# Pendulum on a Cart: Lagrangian Mechanics

A cart of mass $m_1$ slides freely on a horizontal rail. A pendulum (bob mass $m_2$, massless rod of length $R$) hangs from the cart. The two bodies are **coupled**: the cart moves the pivot, and the swinging bob pushes back on the cart.

| Symbol | Meaning |
|:---:|:---|
| $z$ | cart position (horizontal) |
| $\theta$ | pendulum angle from straight down |
| $m_1,\ m_2$ | cart mass, bob mass |
| $R$ | rod length |
| $g$ | gravitational acceleration |

**Why Lagrangian mechanics?** Newton's method needs every force, including the unknown rod tension, which must then be eliminated. The Lagrangian method uses only **energies** and coordinates that already respect the constraints. The equations of motion follow mechanically.

## 1. Generalized coordinates

The system has two degrees of freedom, $q=(z,\theta)$. Taking the pivot as the origin of height, the bob's position is

$$
x = z + R\sin\theta, \qquad y = -R\cos\theta
$$

$$
\dot x = \dot z + R\dot\theta\cos\theta, \qquad \dot y = R\dot\theta\sin\theta
$$

## 2. Energies

$$
T_1 = \tfrac{1}{2}m_1\dot z^{2}
$$

$$
T_2 = \tfrac{1}{2}m_2\left(\dot x^{2}+\dot y^{2}\right)
= \tfrac{1}{2}m_2\left(\dot z^{2} + 2R\,\dot z\dot\theta\cos\theta + R^{2}\dot\theta^{2}\right)
$$

$$
V = m_2 g\,y = -\,m_2 g R\cos\theta
$$

## 3. The Lagrangian

$$
\mathcal{L} = T_1 + T_2 - V
= \tfrac{1}{2}(m_1+m_2)\dot z^{2}
+ m_2 R\,\dot z\,\dot\theta\cos\theta
+ \tfrac{1}{2}m_2R^{2}\dot\theta^{2}
+ m_2 g R\cos\theta
$$

The cross term $m_2R\,\dot z\,\dot\theta\cos\theta$ is the **coupling** between cart and pendulum.

## 4. Euler-Lagrange equations

For each coordinate $q_i \in \{z,\theta\}$:

$$
\frac{d}{dt}\!\left(\frac{\partial\mathcal{L}}{\partial\dot q_i}\right)-\frac{\partial\mathcal{L}}{\partial q_i}=0
$$

**Cart** ($q=z$):

$$
(m_1+m_2)\,\ddot z + m_2R\left(\ddot\theta\cos\theta-\dot\theta^{2}\sin\theta\right)=0
$$

**Pendulum** ($q=\theta$):

$$
R\,\ddot\theta + \ddot z\cos\theta + g\sin\theta = 0
$$

## 5. Solving for the accelerations

These two equations are linear in $(\ddot z,\ddot\theta)$. Solving them (SymPy does this in the code) gives

$$
\boxed{\;\ddot z=\frac{m_2\sin\theta\left(g\cos\theta+R\dot\theta^{2}\right)}{m_1+m_2\sin^{2}\theta}\;}
$$

$$
\boxed{\;\ddot\theta=-\frac{(m_1+m_2)\,g\sin\theta+m_2R\,\dot\theta^{2}\sin\theta\cos\theta}{R\left(m_1+m_2\sin^{2}\theta\right)}\;}
$$

## 6. Conservation laws (used as accuracy checks)

**Energy.** $\mathcal{L}$ has no explicit time dependence, so

$$
E = T + V = \tfrac12(m_1+m_2)\dot z^{2}+m_2R\,\dot z\dot\theta\cos\theta+\tfrac12 m_2R^{2}\dot\theta^{2}-m_2gR\cos\theta = \text{const}
$$

**Horizontal momentum.** $z$ does not appear in $\mathcal{L}$ (a *cyclic coordinate*), so by Noether's theorem

$$
p_z=\frac{\partial\mathcal{L}}{\partial\dot z}=(m_1+m_2)\dot z+m_2R\,\dot\theta\cos\theta=\text{const}
$$

The centre of mass therefore moves at constant velocity

$$
v_{\rm cm}=\frac{p_z}{m_1+m_2}
$$

The cart drifts because the initial push gives $p_z\neq0$, even though no horizontal external force acts.

## 7. Numerical method

With state $S=(\theta,\,z,\,\dot\theta,\,\dot z)$ the system becomes first-order:

$$
\dot S=\big(\dot\theta,\ \dot z,\ \ddot\theta(\theta,\dot\theta),\ \ddot z(\theta,\dot\theta)\big)
$$

It is integrated with an 8th-order Runge-Kutta method (DOP853). Accuracy is verified by checking that $E(t)$ and $p_z(t)$ stay flat.

## 8. Animation notes

- Wheels roll without slipping, so the wheel angle is $\phi=-z/r_w$.
- The purple diamond is the centre of mass, which moves in a straight line at constant speed.
- The fading trail is the bob's recent path.

In [1]:
%matplotlib inline
import numpy as np
import sympy as smp
import matplotlib.pyplot as plt
from matplotlib.patches import Circle, Rectangle, FancyBboxPatch
from matplotlib.collections import LineCollection
from matplotlib.colors import to_rgba
from matplotlib.animation import FuncAnimation
from matplotlib.gridspec import GridSpec
from scipy.integrate import solve_ivp
from IPython.display import HTML, Image, display

plt.rcParams['animation.embed_limit'] = 100  # MB

# ---- Physical parameters ----
g_, m1_, m2_, R_ = 9.8, 2.0, 2.0, 1.5

# ---- Initial conditions ----
th0, z0, w0, zd0 = 0.0, 0.0, 3.0, 0.0   # angle, cart pos, ang. velocity, cart velocity
ZERO_DRIFT = False                       # True -> total momentum = 0 (cart stays near origin)

# ---- Simulation ----
T_END, FPS = 10, 30

if ZERO_DRIFT:
    zd0 = -m2_ * R_ * w0 * np.cos(th0) / (m1_ + m2_)

In [2]:
t = smp.symbols('t')
g, m1, m2, R = smp.symbols('g m1 m2 R', positive=True)
z  = smp.Function('z')(t)
th = smp.Function('th')(t)

# Kinematics and Lagrangian
x, y = z + R*smp.sin(th), -R*smp.cos(th)
L = (m1*z.diff(t)**2 + m2*(x.diff(t)**2 + y.diff(t)**2))/2 - m2*g*y

# Euler-Lagrange equations
EL = lambda q: smp.diff(L, q) - smp.diff(smp.diff(L, q.diff(t)), t)

# Replace functions by plain symbols so they can be solved and lambdified
zdd, thdd, w, q = smp.symbols('zdd thdd w q')
def clean(e):
    return (e.subs({z.diff(t, 2): zdd, th.diff(t, 2): thdd})
             .subs(th.diff(t), w).subs(th, q))

sol = smp.solve([clean(EL(z)), clean(EL(th))], [zdd, thdd], dict=True)[0]
zdd_expr, thdd_expr = smp.simplify(sol[zdd]), smp.simplify(sol[thdd])

display(smp.Eq(smp.Symbol(r'\ddot{z}'), zdd_expr))
display(smp.Eq(smp.Symbol(r'\ddot{\theta}'), thdd_expr))

# Fast numeric function: parameters stay arguments, so no re-derivation is needed
acc = smp.lambdify((q, w, m1, m2, R, g), [zdd_expr, thdd_expr], 'numpy')

Eq(\ddot{z}, m2*(R*w**2 + g*cos(q))*sin(q)/(m1 + m2*sin(q)**2))

Eq(\ddot{\theta}, -(R*m2*w**2*cos(q) + g*m1 + g*m2)*sin(q)/(R*(m1 + m2*sin(q)**2)))

In [3]:
def rhs(_, S):
    q_, _z, w_, v_ = S
    a_z, a_th = acc(q_, w_, m1_, m2_, R_, g_)
    return [w_, v_, a_th, a_z]

tim = np.linspace(0, T_END, T_END*FPS + 1)
res = solve_ivp(rhs, (0, T_END), [th0, z0, w0, zd0], t_eval=tim,
                method='DOP853', rtol=1e-10, atol=1e-10)
th_, zc, w_, zd = res.y

# Positions (pivot is at height 0, bob hangs below)
xb, yb = zc + R_*np.sin(th_), -R_*np.cos(th_)
xcom = (m1_*zc + m2_*xb)/(m1_ + m2_)

# Energy and momentum
KE = 0.5*(m1_+m2_)*zd**2 + m2_*R_*zd*w_*np.cos(th_) + 0.5*m2_*R_**2*w_**2
PE = -m2_*g_*R_*np.cos(th_)
E  = KE + PE
Pz = (m1_+m2_)*zd + m2_*R_*w_*np.cos(th_)

print(f"Energy drift   : {np.ptp(E):.2e} J")
print(f"Momentum drift : {np.ptp(Pz):.2e} kg·m/s")
print(f"COM velocity   : {Pz[0]/(m1_+m2_):.3f} m/s")

Energy drift   : 8.27e-09 J
Momentum drift : 2.55e-09 kg·m/s
COM velocity   : 2.250 m/s


In [4]:
# ---- Geometry (y = 0 is the pivot, at the bottom centre of the cart) ----
HALF = 4.0                          # half-width of the camera window
cart_w, cart_h = 0.9, 0.45          # cart body sits ABOVE y = 0
wheel_r, wheel_dx = 0.12, 0.28      # wheels centred on y = 0, so they touch the rail
rail_h = 0.08                       # rail top is at y = -wheel_r
ground_y = -2.0                     # top of the ground strip
bob_r, TRAIL = 0.10*m2_**(1/3), 45
span = 2*HALF + 2                   # drawn width of rail / ground

fig = plt.figure(figsize=(9, 6.2), dpi=80)
gs = GridSpec(2, 2, height_ratios=[2.3, 1], hspace=0.35, wspace=0.25)
ax, axt, axe = (fig.add_subplot(gs[0, :]), fig.add_subplot(gs[1, 0]), fig.add_subplot(gs[1, 1]))

ax.set(aspect='equal', ylim=(-2.5, 1.0), xlim=(-HALF, HALF), xticks=[], yticks=[], facecolor='#eaf2fb')
for s in ax.spines.values():
    s.set_visible(False)

# Ground strip with ruler (bottom), rail (under the wheels)
ground = ax.add_patch(Rectangle((0, ground_y - 0.35), span, 0.35, fc='#8a7f72', ec='black', lw=1.2, zorder=1))
ruler  = ax.add_collection(LineCollection([], colors='white', linewidths=1, zorder=2))
labels = [ax.text(0, ground_y - 0.2, '', ha='center', va='center', fontsize=8, color='white', zorder=2)
          for _ in range(10)]
rail   = ax.add_patch(Rectangle((0, -wheel_r - rail_h), span, rail_h, fc='#5b6670', ec='black', lw=1.5, zorder=1))

# Cart body (above the pivot) and wheels (on the rail)
cart = ax.add_patch(FancyBboxPatch((0, 0), cart_w, cart_h, boxstyle="round,pad=0,rounding_size=0.06",
                                   fc='dodgerblue', ec='black', lw=2, zorder=3))
cart_txt = ax.text(0, cart_h/2, f"{m1_:g} kg", ha='center', va='center',
                   color='white', weight='bold', fontsize=9, zorder=5)
wheels = [ax.add_patch(Circle((0, 0), wheel_r, fc='#d9d9d9', ec='black', lw=1.5, zorder=4)) for _ in range(2)]
spokes = [ax.plot([], [], color='black', lw=1.2, zorder=4.5)[0] for _ in range(2)]

# Pendulum (hangs below the pivot, drawn in front of the rail)
trail = ax.add_collection(LineCollection([], linewidths=2.5, zorder=5))
rod,   = ax.plot([], [], '-', lw=3, color='#444444', zorder=6)
pivot, = ax.plot([], [], 'o', ms=6, color='black', zorder=8)
bob    = ax.add_patch(Circle((0, 0), bob_r, fc='tomato', ec='black', lw=2, zorder=7))
com,   = ax.plot([], [], 'D', color='purple', ms=7, zorder=8, label='centre of mass')
info   = ax.text(0.015, 0.96, '', transform=ax.transAxes, va='top', family='monospace', fontsize=9)
ax.legend(loc='upper right', fontsize=8, frameon=False)

# Lower plots
axt.plot(tim, np.degrees(th_), color='tomato')
axt.set(xlabel='t (s)', ylabel='θ (deg)'); axt.grid(alpha=0.4)
axe.plot(tim, KE, c='dodgerblue', label='Kinetic')
axe.plot(tim, PE, c='tomato', label='Potential')
axe.plot(tim, E, 'k--', label='Total')
axe.set(xlabel='t (s)', ylabel='Energy (J)'); axe.grid(alpha=0.4)
axe.legend(fontsize=7, loc='upper right', ncol=3)
cur_t, cur_e = axt.axvline(0, c='k', lw=1), axe.axvline(0, c='k', lw=1)

# Precompute everything that does not change per frame
phi = -zc / wheel_r                          # rolling right -> clockwise rotation
cp, sp = np.cos(phi), np.sin(phi)
trail_rgba = np.array(to_rgba('tomato'))
sgns = (-1, 1)

def update(f):
    zf = zc[f]
    ax.set_xlim(zf - HALF, zf + HALF)

    # Rail, ground, ruler, labels (follow the camera)
    rail.set_x(zf - HALF - 1); ground.set_x(zf - HALF - 1)
    ks = np.arange(np.floor((zf - 5)*2)/2, zf + 5, 0.5)
    ruler.set_segments([[(k, ground_y), (k, ground_y - 0.1)] for k in ks])
    ints = np.arange(np.ceil(zf - 4.2), np.floor(zf + 4.2) + 1)
    for i, lab in enumerate(labels):
        if i < len(ints):
            lab.set_position((ints[i], ground_y - 0.24)); lab.set_text(f"{int(ints[i])} m"); lab.set_visible(True)
        else:
            lab.set_visible(False)

    # Cart and rolling wheels
    cart.set_x(zf - cart_w/2); cart_txt.set_position((zf, cart_h/2))
    for k, s in enumerate(sgns):
        cx = zf + s*wheel_dx
        wheels[k].center = (cx, 0)
        c1, s1, c2, s2 = cp[f], sp[f], -sp[f], cp[f]   # two perpendicular spokes
        spokes[k].set_data([cx + wheel_r*c1, cx - wheel_r*c1, np.nan, cx + wheel_r*c2, cx - wheel_r*c2],
                           [wheel_r*s1, -wheel_r*s1, np.nan, wheel_r*s2, -wheel_r*s2])

    # Pendulum, trail, centre of mass
    rod.set_data([zf, xb[f]], [0, yb[f]]); pivot.set_data([zf], [0]); bob.center = (xb[f], yb[f])
    i0 = max(0, f - TRAIL)
    pts = np.column_stack([xb[i0:f+1], yb[i0:f+1]])
    if len(pts) > 1:
        segs = np.stack([pts[:-1], pts[1:]], axis=1)
        cols = np.tile(trail_rgba, (len(segs), 1)); cols[:, 3] = np.linspace(0.05, 0.85, len(segs))
        trail.set_segments(segs); trail.set_color(cols)
    com.set_data([xcom[f]], [ground_y + 0.14])

    info.set_text(f"t = {tim[f]:5.2f} s\nθ = {np.degrees(th_[f]):7.1f}°\nv_cart = {zd[f]:6.2f} m/s")
    cur_t.set_xdata([tim[f]]*2); cur_e.set_xdata([tim[f]]*2)

ani = FuncAnimation(fig, update, frames=len(tim), interval=1000/FPS, blit=False)
plt.close(fig)

In [5]:
ani.save("cart_pendulum.gif", writer="pillow", fps=FPS)   # saves next to your notebook
HTML(ani.to_jshtml())                                      # interactive player in the notebook